# 03 · Case studies, the low-frequency fix, and RR trends

1. **Sample windows**: ECG, PPG and impedance on one clock, with what each method looks at — R peaks,
   pulse peaks, the impedance breaths that define the reference, the respiratory signals derived from
   the ECG/PPG, the breaths CtO accepts, and the spectra with the peak each rule picks.
2. **The low-frequency fix**: every method as published vs corrected, on held-out patients.
3. **Trends**: whole recordings of test patients, and whether each estimator follows *changes* in RR.

The monitor exports no numeric RR (the capnography/spirometry RR trend columns are empty), so the
reference is the breath-by-breath rate from the impedance waveform. All charts are interactive and work
offline; zoom into a panel to compare the signals beat by beat.

In [1]:
import sys, os, json
from pathlib import Path
ROOT = Path.cwd() if (Path.cwd() / "estimate_rr").exists() else Path.cwd().parent
os.chdir(ROOT); sys.path.insert(0, str(ROOT))

import numpy as np, pandas as pd
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from IPython.display import HTML, Markdown, display

from data_prep.build_dataset import TARGET_FS
from estimate_rr.resp_signals import RESP_FS
from scripts.case_study import window_detail, pick_cases, trend_concordance, rolling_trend
from common.metrics import rr_metrics
from estimate_rr import METHODS

DATA, RUNS = Path("dataset/01NVa_monitor"), Path("runs")
BLUE, ORANGE, AQUA, GRAY, INK2, VIOLET = "#2a78d6", "#eb6834", "#1baf7a", "#c3c2b7", "#52514e", "#6250d6"
MOD_COLORS = {"bw": BLUE, "am": ORANGE, "fm": AQUA}
_plotly_js_embedded = False

def show(fig, height=None):
    """Render a plotly figure with plotly.js embedded once, so the exported HTML works offline."""
    global _plotly_js_embedded
    fig.update_layout(template="simple_white", height=height, margin=dict(l=60, r=20, t=60, b=40),
                      font=dict(family="system-ui, sans-serif", size=12))
    display(HTML(fig.to_html(include_plotlyjs=not _plotly_js_embedded, full_html=False)))
    _plotly_js_embedded = True

windows = pd.read_parquet(DATA / "windows_w60_s30.parquet")
test = pd.read_csv(RUNS / "ppg_mod_w60_f0" / "test_predictions.csv").rename(columns={"pred_rr": "dl_mod"})
test["hr"] = windows.loc[test.window_row, "ppg_hr"].to_numpy()
cases = pick_cases(test, windows, trad_col="none")
cases.drop(columns=["window_row", "trad"]).round(1)

,case,segment_id,patient_id,start_s,ref_rr,dl,hr
0,Typical window,01NVA-003-2241_24032021_seg00,01NVA-003-2241,71430.0,22.5,21.6,85.7
1,Fast breathing near HR/2,01NVA-003-2109_19102020_seg00,01NVA-003-2109,1290.0,42.1,40.5,83.3
2,Slowest breathing,01NVA-003-2047_10032022_seg00,01NVA-003-2047,6870.0,6.6,26.2,76.9
3,Largest DL error,01NVA-003-2066_27062022_seg00,01NVA-003-2066,16560.0,12.0,39.4,92.3


## 1 · Sample windows

For each window: **(a)** the signals on one time axis, **(b)** the spectra of the derived respiratory
signals, **(c)** every method's rate. Markers show the regions each method uses:

* ECG ▲ = R peaks (beat times → FM; R amplitude → AM; R/Q mean → BW)
* PPG ▲ = systolic peaks, ▼ = pulse onsets (peak − onset → AM; their mean → BW)
* Impedance ● = breaths found by count-adv: **the reference**
* Derived signals ● = breaths CtO accepts (peaks above 0.2 × Q3 with exactly one trough below zero between them)
* Spectra: dashed = fitted 1/f background, orange = peak the *published* rule picks (largest),
  blue = peak the *corrected* rule picks (highest above background), grey = reference, dark dash = HR/2.

In [2]:
def plot_signals(det, title):
    raw = det["raw"]
    fig = make_subplots(5, 1, shared_xaxes=True, vertical_spacing=0.035,
                        subplot_titles=("ECG (monitor lead) · R peaks", "PPG (monitor Pleth) · pulse peaks / onsets",
                                        f"Impedance (conditioned) · reference breaths → {det['ref_rr']:.1f} bpm",
                                        "PPG-derived respiratory signals · CtO breaths", "ECG-derived respiratory signals · CtO breaths"))
    t = {k: np.arange(len(v)) / TARGET_FS[k] for k, v in raw.items()}
    fig.add_trace(go.Scattergl(x=t["ecg"], y=raw["ecg"], line=dict(color=INK2, width=1), name="ECG", showlegend=False), 1, 1)
    r = det["rpeaks"]; fig.add_trace(go.Scatter(x=t["ecg"][r], y=raw["ecg"][r], mode="markers", marker=dict(symbol="triangle-up", color=ORANGE, size=7), name="R peak", showlegend=False), 1, 1)
    fig.add_trace(go.Scattergl(x=t["ppg"], y=raw["ppg"], line=dict(color=INK2, width=1), name="PPG", showlegend=False), 2, 1)
    p, o = det["ppg_peaks"], det["ppg_onsets"]
    fig.add_trace(go.Scatter(x=t["ppg"][p], y=raw["ppg"][p], mode="markers", marker=dict(symbol="triangle-up", color=ORANGE, size=7), showlegend=False, name="pulse peak"), 2, 1)
    fig.add_trace(go.Scatter(x=t["ppg"][o], y=raw["ppg"][o], mode="markers", marker=dict(symbol="triangle-down", color=BLUE, size=7), showlegend=False, name="onset"), 2, 1)
    tr = np.arange(len(det["resp"])) / RESP_FS
    fig.add_trace(go.Scatter(x=tr, y=det["resp"], line=dict(color=INK2, width=2), showlegend=False, name="impedance"), 3, 1)
    b = det["ref_breaths"]; bi = np.clip(np.round(b * RESP_FS).astype(int), 0, len(tr) - 1)
    fig.add_trace(go.Scatter(x=b, y=det["resp"][bi], mode="markers", marker=dict(color=ORANGE, size=9), showlegend=False, name="breath"), 3, 1)
    for row, sig in ((4, "ppg"), (5, "ecg")):
        for m, y in det[f"{sig}_derived"].items():
            yn = y / (y.std() + 1e-12); ty = np.arange(len(y)) / RESP_FS
            fig.add_trace(go.Scatter(x=ty, y=yn, line=dict(color=MOD_COLORS[m], width=1.6), name=m.upper(), legendgroup=m, showlegend=(row == 4)), row, 1)
            bb = det[f"{sig}_cto_breaths"][m]; bi = np.clip(np.round(bb * RESP_FS).astype(int), 0, len(y) - 1)
            fig.add_trace(go.Scatter(x=bb, y=yn[bi], mode="markers", marker=dict(color=MOD_COLORS[m], size=7, line=dict(color="white", width=1.5)), legendgroup=m, showlegend=False, hovertemplate=m.upper() + " breath %{x:.1f} s<extra></extra>"), row, 1)
    fig.update_yaxes(showticklabels=False); fig.update_xaxes(title_text="time in window (s)", row=5, col=1)
    fig.update_annotations(font_size=12, x=0, xanchor="left")
    fig.update_layout(title=title, legend=dict(orientation="h", y=1.06, x=1, xanchor="right"))
    show(fig, 900)

def plot_spectra(det):
    fig = make_subplots(2, 3, shared_xaxes=True, horizontal_spacing=0.05, vertical_spacing=0.12,
                        subplot_titles=[f"{s.upper()} · {m.upper()}" for s in ("ppg", "ecg") for m in ("bw", "am", "fm")])
    for i, sig in enumerate(("ppg", "ecg"), start=1):
        for j, m in enumerate(("bw", "am", "fm"), start=1):
            sp = det[f"{sig}_spectra"].get(m)
            if sp is None: continue
            fig.add_trace(go.Scatter(x=sp["f_bpm"], y=sp["psd"], line=dict(color=MOD_COLORS[m], width=2), showlegend=False, hovertemplate="%{x:.1f} bpm<extra></extra>"), i, j)
            fig.add_trace(go.Scatter(x=sp["f_bpm"], y=sp["background"], line=dict(color=INK2, width=1, dash="dash"), showlegend=False, hoverinfo="skip"), i, j)
            fig.add_vrect(x0=4, x1=8, fillcolor=GRAY, opacity=0.2, line_width=0, row=i, col=j)
            for x, color, dash in ((det["ref_rr"], GRAY, "solid"), (sp["pick_published"], ORANGE, "dot"),
                                   (sp["pick_corrected"], BLUE, "solid"), (0.5 * det[f"{sig}_hr"], INK2, "dash")):
                if np.isfinite(x): fig.add_vline(x=x, line_color=color, line_dash=dash, line_width=2, row=i, col=j)
    fig.update_yaxes(type="log", showticklabels=False); fig.update_xaxes(range=[0, 62], title_text="breaths/min", row=2)
    fig.update_annotations(font_size=12)
    fig.update_layout(title="Spectra of the derived signals (shaded = below 8 bpm)")
    show(fig, 520)

def rates_table(det, dl):
    t = det["rates"].pivot_table(index="method", columns=["signal", "rule"], values="smart fusion")
    t = t.reindex(["CtO", "CtA", "PKS", "ZeX", "FTS", "WCH", "ARS", "ARM", "ARP"])
    t.columns = [f"{s} {r}" for s, r in t.columns]
    ref = det["ref_rr"]
    display(Markdown(f"**Reference {ref:.1f} bpm · DL (PPG) {dl:.1f} bpm** — smart-fusion estimates; blank = rejected "
                     "because BW/AM/FM disagree by more than 4 bpm. Colour = absolute error."))
    display(t.style.format("{:.1f}", na_rep="–").background_gradient(cmap="Oranges", vmin=0, vmax=10, gmap=(t - ref).abs(), axis=None)
            .highlight_null(color="#fcfcfb"))

details = {}
for c in cases.itertuples():
    det = window_detail(c.segment_id, c.start_s); details[c.case] = det
    display(Markdown(f"### {c.case}\n`{c.segment_id}` at {c.start_s:.0f} s · HR {c.hr:.0f} bpm · RR/HR {c.ref_rr / c.hr:.2f}"))
    plot_signals(det, f"{c.case}: reference {det['ref_rr']:.1f} bpm, DL {c.dl:.1f} bpm")
    plot_spectra(det)
    rates_table(det, c.dl)

### Typical window
`01NVA-003-2241_24032021_seg00` at 71430 s · HR 86 bpm · RR/HR 0.26

**Reference 22.5 bpm · DL (PPG) 21.6 bpm** — smart-fusion estimates; blank = rejected because BW/AM/FM disagree by more than 4 bpm. Colour = absolute error.

,ECG corrected,ECG published,PPG corrected,PPG published
method,,,,
CtO,21.2,21.2,21.1,21.1
CtA,21.3,17.0,22.6,18.9
PKS,25.7,18.7,24.7,21.3
ZeX,20.9,15.7,24.0,17.3
FTS,–,–,22.8,6.9
WCH,21.4,–,22.7,6.6
ARS,23.6,–,22.9,–
ARM,20.3,–,22.9,6.8
ARP,23.7,–,22.9,22.9


### Fast breathing near HR/2
`01NVA-003-2109_19102020_seg00` at 1290 s · HR 83 bpm · RR/HR 0.50

**Reference 42.1 bpm · DL (PPG) 40.5 bpm** — smart-fusion estimates; blank = rejected because BW/AM/FM disagree by more than 4 bpm. Colour = absolute error.

...

**Reference 6.6 bpm · DL (PPG) 26.2 bpm** — smart-fusion estimates; blank = rejected because BW/AM/FM disagree by more than 4 bpm. Colour = absolute error.

,ECG corrected,ECG published,PPG corrected,PPG published
method,,,,
CtO,–,–,8.1,8.1
CtA,14.0,7.1,15.3,7.7
PKS,15.7,7.0,17.4,8.1
ZeX,–,6.9,14.8,7.2
FTS,–,6.2,–,6.3
WCH,–,6.4,–,6.0
ARS,–,7.1,–,7.0
ARM,–,6.9,–,6.6
ARP,–,7.2,–,7.1


### Largest DL error
`01NVA-003-2066_27062022_seg00` at 16560 s · HR 92 bpm · RR/HR 0.13

**Reference 12.0 bpm · DL (PPG) 39.4 bpm** — smart-fusion estimates; blank = rejected because BW/AM/FM disagree by more than 4 bpm. Colour = absolute error.

,ECG published,PPG corrected,PPG published
method,,,
CtO,–,32.3,32.3
CtA,–,26.7,–
PKS,–,33.6,–
ZeX,–,28.3,23.3
FTS,7.4,–,–
WCH,8.1,–,–
ARS,9.3,–,10.4
ARM,8.6,–,–
ARP,–,–,–


### What the sample windows show

(Observations refer to the windows listed at the top; they are chosen deterministically from fold-0 test patients.)

* **Typical window** (`2241`, RR 22.5, HR 86): R peaks, pulse peaks and impedance breaths line up and all three
  derived signals carry the breathing. Every derived spectrum also has a large hump below 8 bpm; the *published*
  spectral rules pick it (6–7 bpm on PPG), the *corrected* rules pick the breathing peak (22.7–22.9 bpm).
  CtA and ZeX under-count as published (17–19 bpm) and are close after half pre-whitening.
* **Fast breathing near HR/2** (`2109`, RR 42, HR 83, ratio 0.50): each breath spans about two beats. The
  spectral methods still find the peak just below HR/2 (41–42 bpm, both rules), but the breath counters miss
  breaths (CtO 38, CtA 31–35, PKS 36–38): the beat-sampled waveform has cycles too small or irregular for their
  thresholds. At high RR/HR the spectral methods are the better choice.
* **Slowest breathing** (`2047`, RR 6.6): the impedance shows genuine slow breaths, so the label is right.
  Here the correction **hurts**: the breathing peak lies inside the low-frequency band the fix discounts, so the
  corrected spectral rules reject the window or return 14–17 bpm, while the published rules return 6–7 bpm. The
  DL model (26 bpm) also fails: under 1 % of training windows are this slow. Slow breathing is the main
  limitation of both the fix and the model.
* **Largest DL error** (`2066`, reference 12, DL 39): the impedance breaths are irregular (intervals 2–8.5 s)
  and the ECG baseline jumps; the signal-processing estimates scatter from 8 to 33 bpm. This is an ambiguous
  window rather than a clean model failure: it passed the reference quality rules because its
  breath-interval CV (0.33) is under the 0.5 limit. A limit of 0.3 would drop it, and 6.6 % of the accepted
  windows with it.

## 2 · The low-frequency fix on held-out patients

Each method as published and corrected, smart fusion, same windows. Correction rules were chosen on
training patients only (see `estimate_rr/__init__.py`).

In [3]:
rows = []
for sig in ("ppg", "ecg"):
    p = RUNS / f"traditional_{sig}_f0" / "predictions.parquet"
    if not p.exists():
        print(f"{sig.upper()}: benchmark not finished"); continue
    b = pd.read_parquet(p)
    for col in [c for c in b.columns if c.endswith("|pub-smart")]:
        method = col.split("|")[0]
        for rule, c2 in (("published", col), ("corrected", f"{method}|smart")):
            m = rr_metrics(b.ref_rr, b[c2], b.patient_id)
            rows.append({"signal": sig.upper(), "method": METHODS[method][1], "rule": rule, "MAE": m["mae"],
                         "bias": m["bias"], "coverage": m["coverage"], "within ±2": m["within_2bpm"]})
fix = pd.DataFrame(rows)
if len(fix):
    t = fix.pivot_table(index=["signal", "method"], columns="rule", values=["MAE", "bias", "coverage"])
    display(t.style.format("{:.2f}"))
    fig = go.Figure()
    for rule, color in (("published", ORANGE), ("corrected", BLUE)):
        d = fix[fix.rule == rule]
        fig.add_trace(go.Bar(x=d.signal + " · " + d.method, y=d.MAE, name=rule, marker_color=color,
                             customdata=np.c_[d.coverage * 100], hovertemplate="%{x}: MAE %{y:.2f} (coverage %{customdata[0]:.0f} %)<extra>" + rule + "</extra>"))
    fig.update_layout(title="MAE of each method, published vs corrected (smart fusion)", barmode="group", yaxis_title="MAE (bpm)", legend=dict(orientation="h", y=1.1))
    show(fig, 420)

ECG: benchmark not finished


## 3 · RR trends over whole recordings

Every 60-s window of a test patient (30-s steps), including windows whose impedance reference failed its
quality checks (faint grey). Lines are 5-minute rolling medians. The patients shown are the three test
patients with the most windows.

In [4]:
tp = RUNS / "trends_f0" / "trend_ppg.parquet"
trend = pd.read_parquet(tp) if tp.exists() else None
if trend is None:
    print("trend file not built yet: python -m scripts.predict_trend --signal ppg --run runs/ppg_mod_w60_f0 --out runs/trends_f0")
else:
    trend = trend.sort_values(["patient_id", "t_epoch"])
    trend["hours"] = (trend.t_epoch - trend.groupby("patient_id").t_epoch.transform("min")) / 3600
    series = [("dl", "DL (PPG)", BLUE), ("count_orig|smart", "CtO smart fusion", ORANGE), ("ar_median|smart", "ARM corrected, smart fusion", AQUA)]
    top = trend.groupby("patient_id").size().sort_values(ascending=False).index[:3]
    for pid in top:
        g = trend[trend.patient_id == pid].copy()
        fig = make_subplots(2, 1, shared_xaxes=True, row_heights=[0.75, 0.25], vertical_spacing=0.05,
                            subplot_titles=("respiratory rate (breaths/min)", "heart rate (beats/min)"))
        ok = g[g.ref_ok]; bad = g[~g.ref_ok]
        fig.add_trace(go.Scattergl(x=bad.hours, y=bad.ref_rr, mode="markers", marker=dict(color=GRAY, size=3), name="reference, failed quality"), 1, 1)
        fig.add_trace(go.Scattergl(x=ok.hours, y=ok.ref_rr, mode="markers", marker=dict(color=INK2, size=4), name="reference"), 1, 1)
        for col, label, color in series:
            fig.add_trace(go.Scattergl(x=g.hours, y=g[col], mode="markers", marker=dict(color=color, size=3, opacity=0.35), legendgroup=label, showlegend=False, hoverinfo="skip"), 1, 1)
            hx, hv = rolling_trend(g, col)
            fig.add_trace(go.Scatter(x=hx, y=hv, line=dict(color=color, width=2), name=label, legendgroup=label), 1, 1)
        hx, hv = rolling_trend(ok, "ref_rr")
        fig.add_trace(go.Scatter(x=hx, y=hv, line=dict(color=INK2, width=2, dash="dot"), name="reference, 5-min median"), 1, 1)
        fig.add_trace(go.Scattergl(x=g.hours, y=g.hr, mode="markers", marker=dict(color=VIOLET, size=3), showlegend=False), 2, 1)
        fig.update_yaxes(range=[0, 60], row=1, col=1); fig.update_xaxes(title_text="hours since start of recording", row=2, col=1)
        m = rr_metrics(ok.ref_rr, ok.dl)
        fig.update_layout(title=f"{pid}: {len(g)} windows, reference usable in {g.ref_ok.mean():.0%}; DL MAE {m['mae']:.2f} bpm",
                          legend=dict(orientation="h", y=-0.18, x=0))
        show(fig, 600)

### Does the estimate follow changes in RR?

Four-quadrant trending analysis (Critchley et al. 2010): for every pair of windows 5 minutes apart in the
same recording, the change in the reference is compared with the change in the estimate. Pairs where the
reference changes by less than 2 bpm are excluded as noise. **Concordance** is the share of pairs in which
both move in the same direction (≥ 90 % is the usual bar for good trending).

In [5]:
if trend is not None:
    ok = trend[trend.ref_ok]
    conc = pd.DataFrame({label: trend_concordance(ok, col) for col, label, _ in series}).T
    display(conc.style.format({"concordance": "{:.0%}", "n_pairs": "{:.0f}", "r_change": "{:.2f}"}))
    fig = make_subplots(1, len(series), shared_yaxes=True, subplot_titles=[s[1] for s in series])
    for i, (col, label, color) in enumerate(series, start=1):
        pairs = []
        for _, g in ok.sort_values("start_s").groupby("segment_id"):
            g = g.set_index("start_s"); common = g.index.intersection(g.index + 300)
            if len(common): pairs.append(pd.DataFrame({"d_ref": g.loc[common].ref_rr.values - g.loc[common - 300].ref_rr.values,
                                                       "d_pred": g.loc[common][col].values - g.loc[common - 300][col].values}))
        p = pd.concat(pairs).dropna()
        fig.add_trace(go.Scattergl(x=p.d_ref, y=p.d_pred, mode="markers", marker=dict(color=color, size=3, opacity=0.3), showlegend=False), 1, i)
        fig.add_shape(type="rect", x0=-2, x1=2, y0=-30, y1=30, fillcolor=GRAY, opacity=0.25, line_width=0, row=1, col=i)
    fig.update_xaxes(range=[-15, 15], title_text="Δ reference over 5 min (bpm)"); fig.update_yaxes(range=[-15, 15])
    fig.update_yaxes(title_text="Δ estimate over 5 min (bpm)", row=1, col=1)
    fig.update_layout(title="Four-quadrant plot (grey band = excluded, |Δ reference| < 2 bpm)")
    show(fig, 420)

,concordance,n_pairs,r_change
DL (PPG),94%,8417,0.84
CtO smart fusion,82%,5495,0.65
"ARM corrected, smart fusion",89%,4011,0.78
